In [2]:
import pandas as pd
import numpy as np
import torch
import torch.nn as nn
from torch.utils.data import Dataset, DataLoader
from sklearn.model_selection import train_test_split
from sklearn.preprocessing import StandardScaler
from transformers import AutoTokenizer, AutoModel
import warnings
from tqdm import tqdm

warnings.filterwarnings('ignore')

# ==================== CONFIGURATION ====================
CONFIG = {
    'csv_path': '/root/final_data.csv',  # CHANGE THIS
    'target_column': 'price',  # CHANGE THIS
    'num_epochs': 30,  # CHANGE THIS
        'mmd_lambda': 0.1,  # CHANGE THIS (0.0 to disable MMD loss)
    
    # Text columns that need BERT embeddings
    'text_embedding_columns': ['summarized_description', 'product_name', 'use_case', 'shelf_life'],
    
    # Loss configuration
    'loss_type': 'log_mse',  # Options: 'log_mse', 'smape', 'mse'
    'log_epsilon': 1.0,  # Small constant added before log to handle values close to 0
    
    # Fixed hyperparameters
    'batch_size': 32,  # Reduced for memory efficiency
    'learning_rate': 0.0001,
    'd_model': 256,
    'nhead': 8,
    'num_layers': 3,
    'dropout': 0.2,
    'val_split': 0.1,
    'bert_model': 'answerdotai/ModernBERT-large',
    'max_length': 64,  # Max tokens for BERT
    'device': 'cuda' if torch.cuda.is_available() else 'cpu'
}

# ==================== LABEL ENCODER WITH UNKNOWN HANDLING ====================
class SafeLabelEncoder:
    """Label encoder that handles unseen labels"""
    def __init__(self):
        self.label_to_idx = {}
        self.unknown_idx = 0
    
    def fit(self, labels):
        unique_labels = pd.Series(labels).dropna().unique()
        # 0 reserved for unknown/NaN
        self.label_to_idx = {label: idx + 1 for idx, label in enumerate(unique_labels)}
        return self
    
    def transform(self, labels):
        return pd.Series(labels).fillna('__UNK__').map(
            lambda x: self.label_to_idx.get(x, self.unknown_idx)
        ).values
    
    def get_num_classes(self):
        return len(self.label_to_idx) + 1

# ==================== TEXT EMBEDDING EXTRACTOR ====================
class BERTEmbeddingExtractor:
    """Memory-efficient BERT embedding extractor"""
    def __init__(self, model_name='bert-base-uncased', max_length=64, device='cpu'):
        self.tokenizer = AutoTokenizer.from_pretrained(model_name)
        self.model = AutoModel.from_pretrained(model_name).to(device)
        self.model.eval()
        self.max_length = max_length
        self.device = device
        # Automatically detect embedding dimension from model config
        self.embedding_dim = self.model.config.hidden_size
        print(f"Encoder embedding dimension: {self.embedding_dim}")
    
    @torch.no_grad()
    def extract_embeddings(self, texts, batch_size=16):
        """Extract embeddings in batches to save memory"""
        embeddings = []
        
        # Convert to list and handle None/NaN
        texts = [str(t) if pd.notna(t) else "" for t in texts]
        
        for i in tqdm(range(0, len(texts), batch_size), desc="Extracting BERT embeddings"):
            batch_texts = texts[i:i + batch_size]
            
            # Tokenize
            encoded = self.tokenizer(
                batch_texts,
                padding=True,
                truncation=True,
                max_length=self.max_length,
                return_tensors='pt'
            ).to(self.device)
            
            # Get embeddings (use [CLS] token)
            outputs = self.model(**encoded)
            batch_embeddings = outputs.last_hidden_state[:, 0, :].cpu().numpy()
            embeddings.append(batch_embeddings)
        
        return np.vstack(embeddings)

# ==================== DATA PREPROCESSING ====================
def preprocess_data(csv_path, target_column, text_cols, val_split=0.1, device='cpu'):
    """Preprocess data with different handling for different feature types"""
    
    # Load data
    df = pd.read_csv(csv_path)
    
    # Drop sample_id if exists
    if 'sample_id' in df.columns:
        df = df.drop('sample_id', axis=1)
    
    # Drop rows with null target
    df = df.dropna(subset=[target_column])
    
    print(f"Total samples after dropping null targets: {len(df)}")
    
    # Separate features and target
    y = df[target_column].values
    X = df.drop(target_column, axis=1)
    
    # Split data first
    X_train, X_val, y_train, y_val = train_test_split(
        X, y, test_size=val_split, random_state=42
    )
    
    print("\n" + "="*50)
    print("FEATURE PROCESSING")
    print("="*50)
    
    # Initialize BERT extractor
    bert_extractor = BERTEmbeddingExtractor(
        model_name=CONFIG['bert_model'],
        max_length=CONFIG['max_length'],
        device=device
    )
    
    # 1. Process text embedding columns (BERT)
    text_embeddings_train = []
    text_embeddings_val = []
    
    for col in text_cols:
        if col in X.columns:
            print(f"\n[TEXT EMBEDDING] {col}")
            train_emb = bert_extractor.extract_embeddings(X_train[col].values)
            val_emb = bert_extractor.extract_embeddings(X_val[col].values)
            text_embeddings_train.append(train_emb)
            text_embeddings_val.append(val_emb)
    
    # 2. Process numerical columns
    numeric_cols = X.select_dtypes(include=[np.number]).columns.tolist()
    print(f"\n[NUMERICAL] {numeric_cols}")
    
    if numeric_cols:
        numeric_train = X_train[numeric_cols].fillna(X_train[numeric_cols].median())
        numeric_val = X_val[numeric_cols].fillna(X_train[numeric_cols].median())
        
        scaler = StandardScaler()
        numeric_train_scaled = scaler.fit_transform(numeric_train)
        numeric_val_scaled = scaler.transform(numeric_val)
    else:
        numeric_train_scaled = np.zeros((len(X_train), 0))
        numeric_val_scaled = np.zeros((len(X_val), 0))
        scaler = None
    
    # 3. Process categorical columns (excluding text embedding columns)
    categorical_cols = [col for col in X.select_dtypes(include=['object']).columns 
                       if col not in text_cols]
    print(f"\n[CATEGORICAL] {categorical_cols}")
    
    label_encoders = {}
    categorical_train_encoded = []
    categorical_val_encoded = []
    
    for col in categorical_cols:
        encoder = SafeLabelEncoder()
        encoder.fit(X_train[col])
        label_encoders[col] = encoder
        
        train_encoded = encoder.transform(X_train[col])
        val_encoded = encoder.transform(X_val[col])
        
        categorical_train_encoded.append(train_encoded)
        categorical_val_encoded.append(val_encoded)
    
    if categorical_train_encoded:
        categorical_train_encoded = np.column_stack(categorical_train_encoded)
        categorical_val_encoded = np.column_stack(categorical_val_encoded)
    else:
        categorical_train_encoded = np.zeros((len(X_train), 0))
        categorical_val_encoded = np.zeros((len(X_val), 0))
    
    # Combine all features
    train_features = {
        'text_embeddings': text_embeddings_train,  # List of embeddings
        'numeric': numeric_train_scaled,
        'categorical': categorical_train_encoded
    }
    
    val_features = {
        'text_embeddings': text_embeddings_val,
        'numeric': numeric_val_scaled,
        'categorical': categorical_val_encoded
    }
    
    metadata = {
        'text_cols': text_cols,
        'numeric_cols': numeric_cols,
        'categorical_cols': categorical_cols,
        'label_encoders': label_encoders,
        'scaler': scaler,
        'num_text_embeddings': len(text_embeddings_train),
        'text_embedding_dim': bert_extractor.embedding_dim,  # Use actual embedding dim
        'num_numeric': len(numeric_cols),
        'num_categorical': len(categorical_cols),
        'vocab_sizes': [enc.get_num_classes() for enc in label_encoders.values()]
    }
    
    print("\n" + "="*50)
    print("FEATURE SUMMARY")
    print("="*50)
    print(f"Text embeddings: {metadata['num_text_embeddings']} columns × {metadata['text_embedding_dim']} dims")
    print(f"Numerical features: {metadata['num_numeric']}")
    print(f"Categorical features: {metadata['num_categorical']}")
    print("="*50 + "\n")
    
    return train_features, val_features, y_train, y_val, metadata

# ==================== DATASET ====================
class MultiModalDataset(Dataset):
    def __init__(self, features, targets):
        self.text_embeddings = [torch.FloatTensor(emb) for emb in features['text_embeddings']]
        self.numeric = torch.FloatTensor(features['numeric'])
        self.categorical = torch.LongTensor(features['categorical'])
        self.targets = torch.FloatTensor(targets)
    
    def __len__(self):
        return len(self.targets)
    
    def __getitem__(self, idx):
        text_embs = [emb[idx] for emb in self.text_embeddings]
        return text_embs, self.numeric[idx], self.categorical[idx], self.targets[idx]

# ==================== MODEL ====================
class MultiModalTransformer(nn.Module):
    def __init__(self, num_text_embeddings, text_embedding_dim, num_numeric, 
                 num_categorical, vocab_sizes, d_model=256, nhead=8, 
                 num_layers=3, dropout=0.2, embedding_dim=32):
        super().__init__()
        
        self.num_text_embeddings = num_text_embeddings
        
        # Text embedding projections (separate for each text column)
        self.text_projections = nn.ModuleList([
            nn.Linear(text_embedding_dim, d_model) for _ in range(num_text_embeddings)
        ])
        
        # Categorical embeddings
        self.categorical_embeddings = nn.ModuleList([
            nn.Embedding(vocab_size, embedding_dim) for vocab_size in vocab_sizes
        ])
        
        # Numeric projection
        if num_numeric > 0:
            self.numeric_projection = nn.Linear(num_numeric, d_model)
        else:
            self.numeric_projection = None
        
        # Categorical projection
        if num_categorical > 0:
            self.categorical_projection = nn.Linear(num_categorical * embedding_dim, d_model)
        else:
            self.categorical_projection = None
        
        # Transformer encoder
        encoder_layer = nn.TransformerEncoderLayer(
            d_model=d_model,
            nhead=nhead,
            dim_feedforward=d_model * 4,
            dropout=dropout,
            batch_first=True
        )
        self.transformer_encoder = nn.TransformerEncoder(encoder_layer, num_layers=num_layers)
        
        # Final prediction head
        self.predictor = nn.Sequential(
            nn.Linear(d_model, d_model // 2),
            nn.ReLU(),
            nn.Dropout(dropout),
            nn.Linear(d_model // 2, 1),
            nn.ReLU() 
        )
    
    def forward(self, text_embeddings, numeric, categorical):
        batch_size = numeric.shape[0]
        features = []
        
        # Process text embeddings
        for i, text_emb in enumerate(text_embeddings):
            projected = self.text_projections[i](text_emb)
            features.append(projected.unsqueeze(1))
        
        # Process numeric features
        if self.numeric_projection is not None and numeric.shape[1] > 0:
            numeric_proj = self.numeric_projection(numeric)
            features.append(numeric_proj.unsqueeze(1))
        
        # Process categorical features
        if self.categorical_projection is not None and categorical.shape[1] > 0:
            cat_embeddings = []
            for i, embedding_layer in enumerate(self.categorical_embeddings):
                cat_embeddings.append(embedding_layer(categorical[:, i]))
            cat_concat = torch.cat(cat_embeddings, dim=1)
            cat_proj = self.categorical_projection(cat_concat)
            features.append(cat_proj.unsqueeze(1))
        
        # Concatenate all features
        all_features = torch.cat(features, dim=1)  # (batch_size, num_features, d_model)
        
        # Transformer encoding
        encoded = self.transformer_encoder(all_features)
        
        # Global average pooling
        pooled = encoded.mean(dim=1)  # (batch_size, d_model)
        
        # Prediction
        output = self.predictor(pooled).squeeze(-1)
        
        return output, pooled  # Return pooled for MMD loss

# ==================== LOSS FUNCTIONS ====================
class LogMSELoss(nn.Module):
    """Log-transformed MSE loss for balanced learning across price ranges"""
    def __init__(self, epsilon=1.0):
        super().__init__()
        self.epsilon = epsilon
    
    def forward(self, predictions, targets):
        log_pred = torch.log(predictions + self.epsilon)
        log_target = torch.log(targets + self.epsilon) 
        return torch.mean((log_pred - log_target) ** 2)

class SMAPELoss(nn.Module):
    """Differentiable SMAPE loss"""
    def __init__(self, epsilon=1e-8):
        super().__init__()
        self.epsilon = epsilon
    
    def forward(self, predictions, targets):
        denominator = torch.abs(predictions) + torch.abs(targets) + self.epsilon
        return 200 * torch.mean(torch.abs(predictions - targets) / denominator)

def get_loss_function(loss_type, epsilon=1.0):
    """Get loss function based on configuration"""
    if loss_type == 'log_mse':
        return LogMSELoss(epsilon=epsilon)
    elif loss_type == 'smape':
        return SMAPELoss()
    elif loss_type == 'mse':
        return nn.MSELoss()
    else:
        raise ValueError(f"Unknown loss type: {loss_type}")

# ==================== MMD LOSS ====================
def gaussian_kernel(x, y, sigma=1.0):
    x_size = x.size(0)
    y_size = y.size(0)
    dim = x.size(1)
    
    x = x.unsqueeze(1)
    y = y.unsqueeze(0)
    
    tiled_x = x.expand(x_size, y_size, dim)
    tiled_y = y.expand(x_size, y_size, dim)
    
    kernel_input = (tiled_x - tiled_y).pow(2).sum(2)
    return torch.exp(-kernel_input / (2 * sigma ** 2))

def mmd_loss(source_features, target_features):
    """Compute MMD on learned feature representations"""
    if len(source_features) == 0 or len(target_features) == 0:
        return torch.tensor(0.0).to(source_features.device)
    
    xx = gaussian_kernel(source_features, source_features).mean()
    yy = gaussian_kernel(target_features, target_features).mean()
    xy = gaussian_kernel(source_features, target_features).mean()
    
    return xx + yy - 2 * xy

# ==================== SMAPE METRIC ====================
def smape(y_true, y_pred):
    denominator = (np.abs(y_true) + np.abs(y_pred))
    diff = np.abs(y_true - y_pred) / denominator
    diff[denominator == 0] = 0.0
    return 200 * np.mean(diff)

# ==================== TRAINING ====================
def train_epoch(model, train_loader, optimizer, criterion, device, mmd_lambda):
    model.train()
    total_loss = 0
    all_preds = []
    all_targets = []
    
    pbar = tqdm(train_loader, desc='Training')
    for text_embs, numeric, categorical, targets in pbar:
        text_embs = [emb.to(device) for emb in text_embs]
        numeric = numeric.to(device)
        categorical = categorical.to(device)
        targets = targets.to(device)
        
        optimizer.zero_grad()
        predictions, features = model(text_embs, numeric, categorical)
        
        # Primary loss (log_mse, smape, or mse)
        primary_loss = criterion(predictions, targets)
        
        # MMD Loss on learned features (not predictions)
        if mmd_lambda > 0:
            # Split batch in half for MMD
            mid = len(features) // 2
            if mid > 0:
                mmd = mmd_loss(features[:mid], features[mid:])
                loss = primary_loss + mmd_lambda * mmd
            else:
                loss = primary_loss
        else:
            loss = primary_loss
        
        loss.backward()
        torch.nn.utils.clip_grad_norm_(model.parameters(), 1.0)
        optimizer.step()
        
        total_loss += loss.item()
        all_preds.extend(predictions.detach().cpu().numpy())
        all_targets.extend(targets.cpu().numpy())
        
        pbar.set_postfix({'loss': loss.item()})
    
    avg_loss = total_loss / len(train_loader)
    train_smape = smape(np.array(all_targets), np.array(all_preds))
    
    return avg_loss, train_smape

def validate(model, val_loader, criterion, device):
    model.eval()
    total_loss = 0
    all_preds = []
    all_targets = []
    
    with torch.no_grad():
        pbar = tqdm(val_loader, desc='Validation')
        for text_embs, numeric, categorical, targets in pbar:
            text_embs = [emb.to(device) for emb in text_embs]
            numeric = numeric.to(device)
            categorical = categorical.to(device)
            targets = targets.to(device)
            
            predictions, _ = model(text_embs, numeric, categorical)
            loss = criterion(predictions, targets)
            
            total_loss += loss.item()
            all_preds.extend(predictions.cpu().numpy())
            all_targets.extend(targets.cpu().numpy())
            
            pbar.set_postfix({'loss': loss.item()})
    
    avg_loss = total_loss / len(val_loader)
    val_smape = smape(np.array(all_targets), np.array(all_preds))
    
    return avg_loss, val_smape

# ==================== MAIN ====================
def main():
    print("=" * 70)
    print("BERT-BASED MULTI-MODAL TRANSFORMER PRICE PREDICTOR")
    print("=" * 70)
    print(f"\nConfiguration:")
    for key, value in CONFIG.items():
        print(f"  {key}: {value}")
    print("\n" + "=" * 70)
    
    # Preprocess data
    print("\n[1/4] Loading and preprocessing data...")
    train_features, val_features, y_train, y_val, metadata = preprocess_data(
        CONFIG['csv_path'],
        CONFIG['target_column'],
        CONFIG['text_embedding_columns'],
        CONFIG['val_split'],
        CONFIG['device']
    )
    
    print(f"Training samples: {len(y_train)}")
    print(f"Validation samples: {len(y_val)}")
    
    # Debug: Check embedding shapes
    print(f"\nDebug - Text embedding shapes:")
    for i, emb in enumerate(train_features['text_embeddings']):
        print(f"  Text embedding {i}: {emb.shape}")
    print(f"Debug - Numeric features shape: {train_features['numeric'].shape}")
    print(f"Debug - Categorical features shape: {train_features['categorical'].shape}")
    
    # Create datasets
    train_dataset = MultiModalDataset(train_features, y_train)
    val_dataset = MultiModalDataset(val_features, y_val)
    
    train_loader = DataLoader(train_dataset, batch_size=CONFIG['batch_size'], shuffle=True)
    val_loader = DataLoader(val_dataset, batch_size=CONFIG['batch_size'], shuffle=False)
    
    # Initialize model
    print("\n[2/4] Initializing model...")
    print(f"Text embedding dimension from encoder: {metadata['text_embedding_dim']}")
    print(f"Number of text embeddings: {metadata['num_text_embeddings']}")
    print(f"Model d_model: {CONFIG['d_model']}")
    
    model = MultiModalTransformer(
        num_text_embeddings=metadata['num_text_embeddings'],
        text_embedding_dim=metadata['text_embedding_dim'],
        num_numeric=metadata['num_numeric'],
        num_categorical=metadata['num_categorical'],
        vocab_sizes=metadata['vocab_sizes'],
        d_model=CONFIG['d_model'],
        nhead=CONFIG['nhead'],
        num_layers=CONFIG['num_layers'],
        dropout=CONFIG['dropout']
    ).to(CONFIG['device'])
    
    total_params = sum(p.numel() for p in model.parameters())
    print(f"Model parameters: {total_params:,}")
    
    # Debug: Print first text projection layer shape
    if len(model.text_projections) > 0:
        first_proj = model.text_projections[0]
        print(f"First text projection layer: {first_proj.in_features} -> {first_proj.out_features}")
    
    # Optimizer and loss
    optimizer = torch.optim.AdamW(model.parameters(), lr=CONFIG['learning_rate'], weight_decay=0.01)
    criterion = get_loss_function(CONFIG['loss_type'], CONFIG.get('log_epsilon', 1.0))
    scheduler = torch.optim.lr_scheduler.ReduceLROnPlateau(optimizer, mode='min', factor=0.5, patience=5)
    
    print(f"\nLoss function: {CONFIG['loss_type']}")
    if CONFIG['loss_type'] == 'log_mse':
        print(f"Log epsilon: {CONFIG['log_epsilon']}")
    
    # Training
    print("\n[3/4] Training model...")
    best_val_smape = float('inf')
    
    for epoch in range(CONFIG['num_epochs']):
        print(f"\nEpoch {epoch + 1}/{CONFIG['num_epochs']}")
        
        train_loss, train_smape = train_epoch(
            model, train_loader, optimizer, criterion,
            CONFIG['device'], CONFIG['mmd_lambda']
        )
        val_loss, val_smape = validate(model, val_loader, criterion, CONFIG['device'])
        
        scheduler.step(val_loss)
        
        print(f"Train Loss: {train_loss:.4f}, Train SMAPE: {train_smape:.2f}%")
        print(f"Val Loss: {val_loss:.4f}, Val SMAPE: {val_smape:.2f}%")
        
        # Save best model based on SMAPE
        if val_smape < best_val_smape:
            best_val_smape = val_smape
            torch.save({
                'epoch': epoch,
                
                'model_state_dict': model.state_dict(),
                'optimizer_state_dict': optimizer.state_dict(),
                'val_loss': val_loss,
                'val_smape': val_smape,
                'metadata': metadata
            }, 'best_model.pth')
            print(f"✓ Best model saved (Val SMAPE: {val_smape:.2f}%)")
    
    print("\n[4/4] Training completed!")
    print(f"Best validation SMAPE: {best_val_smape:.2f}%")
    print("\nModel saved as 'best_model.pth'")

if __name__ == "__main__":
    main()

BERT-BASED MULTI-MODAL TRANSFORMER PRICE PREDICTOR

Configuration:
  csv_path: /root/final_data.csv
  target_column: price
  num_epochs: 30
  mmd_lambda: 0.1
  text_embedding_columns: ['summarized_description', 'product_name', 'use_case', 'shelf_life']
  loss_type: log_mse
  log_epsilon: 1.0
  batch_size: 32
  learning_rate: 0.0001
  d_model: 256
  nhead: 8
  num_layers: 3
  dropout: 0.2
  val_split: 0.1
  bert_model: answerdotai/ModernBERT-large
  max_length: 64
  device: cuda


[1/4] Loading and preprocessing data...
Total samples after dropping null targets: 75000

FEATURE PROCESSING


tokenizer_config.json: 0.00B [00:00, ?B/s]

tokenizer.json: 0.00B [00:00, ?B/s]

special_tokens_map.json:   0%|          | 0.00/694 [00:00<?, ?B/s]

config.json: 0.00B [00:00, ?B/s]

...

Train Loss: 0.1630, Train SMAPE: 31.51%
Val Loss: 0.5369, Val SMAPE: 52.77%
✓ Best model saved (Val SMAPE: 52.77%)

Epoch 29/30


Validation: 100%|████████████████████████████████████████████████| 235/235 [00:01<00:00, 159.07it/s, loss=1.12]


Train Loss: 0.1530, Train SMAPE: 30.58%
Val Loss: 0.5437, Val SMAPE: 52.84%

Epoch 30/30


Validation: 100%|████████████████████████████████████████████████| 235/235 [00:01<00:00, 165.79it/s, loss=1.12]


Train Loss: 0.1494, Train SMAPE: 30.17%
Val Loss: 0.5474, Val SMAPE: 52.93%

[4/4] Training completed!
Best validation SMAPE: 52.77%

Model saved as 'best_model.pth'
